In [20]:
import numpy as np
from IPython.display import display, Audio # for playing audio
import soundfile as sf # read n write audio
import wave # dataset audio .wav
from pydub import AudioSegment # audio editing
import librosa # add audio effects
import torch, torchaudio
import matplotlib.pyplot as plt

In [2]:
import sys
import torch
import torchaudio
import importlib.metadata as md

print("Python:", sys.executable)
print("PyTorch:", torch.__version__)
print("TorchAudio:", torchaudio.__version__)
print("TorchCodec:", md.version("torchcodec"))

Python: c:\Users\Hans\AppData\Local\Programs\Python\Python313\python.exe
PyTorch: 2.12.0+cpu
TorchAudio: 2.11.0+cpu
TorchCodec: 0.17.0


In [3]:
AUDIO_FILE = './sample.wav'

In [4]:
# audio component
# sample rate = ada brp samples per second, biasanya 16000hz
# sample width = bytes per sample
# duration = number of samples


data, sr = sf.read(AUDIO_FILE)

print("Sample rate: ", sr)
print("Sample: ", len(data))
print("Duration: ", len(data)/sr)
print("First 5 data: ", data[:5])

Sample rate:  16000
Sample:  480000
Duration:  30.0
First 5 data:  [ 4.27246094e-04  3.05175781e-05 -1.83105469e-04  6.10351562e-05
 -9.15527344e-05]


In [ ]:
# display audio
display(Audio(AUDIO_FILE))



ValueError: rate must be specified when data is a numpy array or list of audio samples.

In [6]:
# write and read
data, sr = sf.read(AUDIO_FILE)

sf.write("new_file.flac", data, sr)

display(Audio("new_file.flac"))

In [7]:
# read file info and write
obj = wave.open(AUDIO_FILE, "r")
print("Channel: ", obj.getnchannels())
print("Sample Width: ", obj.getsampwidth())
print("Frame Rate: ", obj.getframerate())
print("Frame: ", obj.getnframes())

# store params and frames
params = obj.getparams()
frames = obj.readframes(obj.getnframes())
obj.close()

# write
obj = wave.open("new_save.wav", "w")
obj.setparams(params)
obj.writeframes(frames)

obj.close()

Channel:  1
Sample Width:  2
Frame Rate:  16000
Frame:  480000


In [29]:
# pydub load, cut, export
sound = AudioSegment.from_wav(AUDIO_FILE)
print("Duration (ms): ", len(sound))

# cut duration audio
first_5s = sound[:5000]
first_5s.export("first_5s.wav", format="wav")
display(Audio("first_5s.wav"))

Duration (ms):  30000


In [9]:
signal, sr = sf.read(AUDIO_FILE)
print("Sample Rate: ", signal)

Sample Rate:  [ 4.27246094e-04  3.05175781e-05 -1.83105469e-04 ...  0.00000000e+00
  0.00000000e+00  0.00000000e+00]


In [10]:
signal, sr = torchaudio.load(AUDIO_FILE)

# shape (channel, samples)
waveform = torch.tensor(signal).unsqueeze(0)
print("Shape: ", waveform.shape)

# change sample rate from 16k to 8k
waveform_8k = torchaudio.transforms.Resample(sr, 8000)(waveform)
print("New sr: ", waveform_8k.shape) 

Shape:  torch.Size([1, 1, 480000])
New sr:  torch.Size([1, 1, 240000])


C:\Users\Hans\AppData\Local\Temp\ipykernel_26252\621697203.py:4: UserWarning: To copy construct from a tensor, it is recommended to use sourceTensor.detach().clone() or sourceTensor.detach().clone().requires_grad_(True), rather than torch.tensor(sourceTensor).
  waveform = torch.tensor(signal).unsqueeze(0)


In [11]:
print("PyTorch:", torch.__version__)
print("CUDA:", torch.version.cuda)

PyTorch: 2.12.0+cpu
CUDA: None


In [12]:
# augmentation

# volume up and down
louder = sound + 6
quieter = sound - 6

louder.export("aug_louder.wav", format="wav")
quieter.export("aug_quieter.wav", format="wav")
display(Audio("aug_louder.wav"), Audio("aug_quieter.wav"))

In [23]:
# white noise
signal, sr = librosa.load(AUDIO_FILE, sr=None)

noise = np.random.normal(0, signal.std(), len(signal))

In [14]:
noisy = signal + noise * 0.5
sf.write("aug_noise.wav", noisy, sr)
display(Audio("aug_noise.wav"))

In [15]:
pitch_up = librosa.effects.pitch_shift(signal, sr=sr, n_steps=4)
pitch_down = librosa.effects.pitch_shift(signal, sr=sr, n_steps=-4)

sf.write("aug_pitch_up.wav", pitch_up, sr)
sf.write("aug_pitch_down.wav", pitch_down, sr)
display(Audio("aug_pitch_up.wav"), Audio("aug_pitch_down.wav"))

c:\Users\Hans\AppData\Local\Programs\Python\Python313\Lib\site-packages\librosa\effects.py:448: FutureWarning: The `hop_length` parameter is deprecated as of 1.0 and will be removed in 1.1. It is unused in the current implementation.
  stft_stretch = core.phase_vocoder(
c:\Users\Hans\AppData\Local\Programs\Python\Python313\Lib\site-packages\librosa\effects.py:448: FutureWarning: The `n_fft` parameter is deprecated as of 1.0 and will be removed in 1.1. It is unused in the current implementation.
  stft_stretch = core.phase_vocoder(
c:\Users\Hans\AppData\Local\Programs\Python\Python313\Lib\site-packages\librosa\effects.py:448: FutureWarning: The `hop_length` parameter is deprecated as of 1.0 and will be removed in 1.1. It is unused in the current implementation.
  stft_stretch = core.phase_vocoder(
c:\Users\Hans\AppData\Local\Programs\Python\Python313\Lib\site-packages\librosa\effects.py:448: FutureWarning: The `n_fft` parameter is deprecated as of 1.0 and will be removed in 1.1. It is u

In [16]:
# speed up and slow down
faster = librosa.effects.time_stretch(signal, rate=1.5)
slower = librosa.effects.time_stretch(signal, rate=0.7)

sf.write("aug_faster.wav", faster, sr)
sf.write("aug_slower.wav", slower, sr)
display(Audio("aug_faster.wav"), Audio("aug_slower.wav"))

c:\Users\Hans\AppData\Local\Programs\Python\Python313\Lib\site-packages\librosa\effects.py:448: FutureWarning: The `hop_length` parameter is deprecated as of 1.0 and will be removed in 1.1. It is unused in the current implementation.
  stft_stretch = core.phase_vocoder(
c:\Users\Hans\AppData\Local\Programs\Python\Python313\Lib\site-packages\librosa\effects.py:448: FutureWarning: The `n_fft` parameter is deprecated as of 1.0 and will be removed in 1.1. It is unused in the current implementation.
  stft_stretch = core.phase_vocoder(


In [17]:
# reverse sound
reversed_sound = sound.reverse()
reversed_sound.export("aug_reverse.wav", format="wav")
display(Audio("aug_reverse.wav"))

In [18]:
# random gain -> random amplitudo audionya
gain = np.random.uniform(0.5, 2.0)
gained = np.clip(signal * gain, -1, 1)
sf.write("aug_gain.wav", gained, sr)
display(Audio("aug_gain.wav"))

In [19]:
# fade in and fade out
faded = sound.fade_in(2000).fade_out(2000)

faded.export("aug_faded.wav", format="wav")

display(Audio("aug_faded.wav"))